<h1 style="text-align: center;"> Welcome to our project! </h1>

<p style="text-align: center;"> Authors: Amariah Robinson, Jenifer Roque-Martinez, Peyton Hamorsky, Kashika Chaudhary </p>

<h3> Library Imports </h3>

Let's make sure that you have everything you need to make our code work for you.

In [1]:
pip install requests pandas boto3 scikit-learn xgboost numpy json 

Note: you may need to restart the kernel to use updated packages.


ERROR: Could not find a version that satisfies the requirement json (from versions: none)
ERROR: No matching distribution found for json


In [ ]:
import json # the format the api data is in
import boto3 # allows AWS server communications
import requests # allows for requests to be made to the API
import pandas as pd # allows for a dataframe to be made! (Organization and Modeling)
import numpy as np # allows for numerical operations to be performed on the data
import xgboost as XGB # allows for xgboost modeling
from datetime import datetime, timezone # allows for conversions from UTC (the format from the API)
from sklearn.ensemble import RandomForestRegressor, RandomForestClassifier # what we want to use to model our project in the future
from sklearn.model_selection import train_test_split # allows for splitting of data into training and testing sets
from sklearn.tree import DecisionTreeClassifier # allows for decision tree modeling
from sklearn.linear_model import LinearRegression, Ridge # allows for linear regression modeling
from sklearn.preprocessing import StandardScaler # used for scaling and leveling out the data 
from sklearn.decomposition import PCA # used 
from sklearn.metrics import r2_score, mean_absolute_error, mean_squared_error # metrics used to evaluate the model
from sklearn.impute import KNNImputer # used for filling in missing values
import logging # used for error catching

<h3> S3 Bucket initiation and usage </h3>

Now that all of our libraries and necessities are installed, we can go ahead and begin with taking data from our S3 bucket and using it to complete models. 

In [3]:
# 1. Initialize S3 client
s3 = boto3.client('s3')

# Where is the data located within my AWS s3??? (Shown below)
BUCKET_NAME = 'api-s3-data-dtsc3601' 
OBJECT_KEY = 'openweatherdata2.json'

# Grabs the object from the bucket to allow it to be read for later usage
# 1. Fetch the object from S3
response = s3.get_object(Bucket=BUCKET_NAME, Key=OBJECT_KEY)
    
# 2. Read and decode the streaming body content
file_content = response['Body'].read().decode('utf-8')

# 3. Parse the string into a Python dictionary
data = json.loads(file_content)

# Fixed try block to safely slice nested lists and flatten them
try:
    # 1. Extract the slice starting from index 1 onward
    # Ensure data is non-empty before indexing [0]
    if not data:
        raise ValueError("The 'data' structure is empty.")

    nested_list = data[1:] 
    print('Extracted Nested List:', nested_list)

    if not nested_list:
        print("The extracted nested list is empty.")
    else:
        # 2. Access the first element of the sliced structure
        first_sub_element = nested_list[0]
        
        # Check if the extracted element is itself a list/tuple before doing 2D indexing [0][0]
        if isinstance(first_sub_element, (list, tuple)) and len(first_sub_element) > 0:
            item = first_sub_element[0]
            print('Specific element (first item of first sub-list):', item)
        else:
            item = first_sub_element
            print('Specific element (first item):', item)

        # 3. Flatten the list (handles both 2D sub-lists and 1D items safely)
        flat_list = []
        for sublist in nested_list:
            if isinstance(sublist, (list, tuple)):
                flat_list.extend(sublist)
            else:
                flat_list.append(sublist)

        print('Flattened list:', flat_list)

except (IndexError, TypeError) as e:
    print(f"Indexing/Type Error: {e}. Check if 'data' is a non-empty list of lists.")
except KeyError as e:
    print(f"KeyError: {e}. Expected key is missing from dictionary.")
except Exception as e:
    print(f"An unexpected error occurred: {e}")


Extracted Nested List: [{'dt': 1759280400, 'dt_iso': '2025-10-01 01:00:00 +0000 UTC', 'timezone': -25200, 'main': {'temp': 61.38, 'temp_min': 60.6, 'temp_max': 63.84, 'feels_like': 59.7, 'pressure': 1016, 'humidity': 53, 'dew_point': 44.11}, 'clouds': {'all': 0}, 'weather': [{'id': 800, 'main': 'Clear', 'description': 'sky is clear', 'icon': '01d'}], 'visibility': 10000, 'wind': {'speed': 9.22, 'deg': 200}, 'lon': -111.651302, 'city_name': 'Flagstaff', 'lat': 35.198284}, {'dt': 1759284000, 'dt_iso': '2025-10-01 02:00:00 +0000 UTC', 'timezone': -25200, 'main': {'temp': 56.5, 'temp_min': 55.69, 'temp_max': 58.84, 'feels_like': 54.77, 'pressure': 1017, 'humidity': 62, 'dew_point': 43.65}, 'clouds': {'all': 0}, 'weather': [{'id': 800, 'main': 'Clear', 'description': 'sky is clear', 'icon': '01n'}], 'visibility': 10000, 'wind': {'speed': 3.44, 'deg': 200}, 'lon': -111.651302, 'city_name': 'Flagstaff', 'lat': 35.198284}, {'dt': 1759287600, 'dt_iso': '2025-10-01 03:00:00 +0000 UTC', 'timezone

<h3> Data Formatting </h3>

Now that we have our data, let's create an easier way to look at all of it, rather than just strings connected to eachother, it will be in a table format (think of an excel spreadsheet.)

In [4]:
# Let's create the pandas DataFrame
try: 
    if flat_list:

# Flatten nested JSON dictionaries (e.g., OpenWeather 'main' or 'wind' sub-dicts)
        df = pd.json_normalize(flat_list)

        print("DataFrame constructed successfully:")
        print(df.head())
        print("\nDataFrame Info:")
        print(df.info())

    else:
        print("No valid list of records found in JSON to create a DataFrame.")

except Exception as e:
    logging.error("Error creating DataFrame: %s", e, exc_info=True)

DataFrame constructed successfully:
           dt                         dt_iso  timezone  \
0  1759280400  2025-10-01 01:00:00 +0000 UTC    -25200   
1  1759284000  2025-10-01 02:00:00 +0000 UTC    -25200   
2  1759287600  2025-10-01 03:00:00 +0000 UTC    -25200   
3  1759291200  2025-10-01 04:00:00 +0000 UTC    -25200   
4  1759294800  2025-10-01 05:00:00 +0000 UTC    -25200   

                                             weather  visibility         lon  \
0  [{'id': 800, 'main': 'Clear', 'description': '...     10000.0 -111.651302   
1  [{'id': 800, 'main': 'Clear', 'description': '...     10000.0 -111.651302   
2  [{'id': 800, 'main': 'Clear', 'description': '...     10000.0 -111.651302   
3  [{'id': 800, 'main': 'Clear', 'description': '...     10000.0 -111.651302   
4  [{'id': 800, 'main': 'Clear', 'description': '...     10000.0 -111.651302   

   city_name        lat  main.temp  main.temp_min  ...  main.humidity  \
0  Flagstaff  35.198284      61.38          60.60  ...       

Let's take a peek at our newly formed dataset.

In [5]:
df.head(5) # allows us to see the first 5 rows of the dataset, minus a couple of columns because we have so many features (variables) within the dataset, your Code Editor might condense some using an ellipses (...) in the middle of the dataset. 

,dt,dt_iso,timezone,weather,visibility,lon,city_name,lat,main.temp,main.temp_min,...,main.humidity,main.dew_point,clouds.all,wind.speed,wind.deg,wind.gust,rain.1h,rain.3h,snow.1h,snow.3h
0,1759280400,2025-10-01 01:00:00 +0000 UTC,-25200,"[{'id': 800, 'main': 'Clear', 'description': '...",10000.0,-111.651302,Flagstaff,35.198284,61.38,60.60,...,53,44.11,0,9.22,200,NaN,NaN,NaN,NaN,NaN
1,1759284000,2025-10-01 02:00:00 +0000 UTC,-25200,"[{'id': 800, 'main': 'Clear', 'description': '...",10000.0,-111.651302,Flagstaff,35.198284,56.50,55.69,...,62,43.65,0,3.44,200,NaN,NaN,NaN,NaN,NaN
2,1759287600,2025-10-01 03:00:00 +0000 UTC,-25200,"[{'id': 800, 'main': 'Clear', 'description': '...",10000.0,-111.651302,Flagstaff,35.198284,53.62,51.40,...,69,43.72,0,0.00,0,NaN,NaN,NaN,NaN,NaN
3,1759291200,2025-10-01 04:00:00 +0000 UTC,-25200,"[{'id': 800, 'main': 'Clear', 'description': '...",10000.0,-111.651302,Flagstaff,35.198284,51.62,50.38,...,73,43.27,0,1.01,27,1.01,NaN,NaN,NaN,NaN
4,1759294800,2025-10-01 05:00:00 +0000 UTC,-25200,"[{'id': 800, 'main': 'Clear', 'description': '...",10000.0,-111.651302,Flagstaff,35.198284,48.49,46.69,...,80,42.62,0,1.01,4,1.99,NaN,NaN,NaN,NaN


In [6]:
df.columns # gives us the names of the columns that are within our dataframe.

Index(['dt', 'dt_iso', 'timezone', 'weather', 'visibility', 'lon', 'city_name',
       'lat', 'main.temp', 'main.temp_min', 'main.temp_max', 'main.feels_like',
       'main.pressure', 'main.humidity', 'main.dew_point', 'clouds.all',
       'wind.speed', 'wind.deg', 'wind.gust', 'rain.1h', 'rain.3h', 'snow.1h',
       'snow.3h'],
      dtype='object')

<h3> Data Cleaning </h3>

In our case, weather has a nested list (a list (inside of a list)), and that can be hard to work with later on for modeling. Based on what we can see within the Weather column, it has information in it that we already have located elsewhere in the dataset such as Clouds, which tells us the percentage of cloud coverage we have in the sky. So let's get rid of the Weather column to help clean up the dataset for later modeling. 

In [7]:
drop_nestedlist = df.drop(columns=["weather"])
drop_nestedlist.head(2)

,dt,dt_iso,timezone,visibility,lon,city_name,lat,main.temp,main.temp_min,main.temp_max,...,main.humidity,main.dew_point,clouds.all,wind.speed,wind.deg,wind.gust,rain.1h,rain.3h,snow.1h,snow.3h
0,1759280400,2025-10-01 01:00:00 +0000 UTC,-25200,10000.0,-111.651302,Flagstaff,35.198284,61.38,60.60,63.84,...,53,44.11,0,9.22,200,NaN,NaN,NaN,NaN,NaN
1,1759284000,2025-10-01 02:00:00 +0000 UTC,-25200,10000.0,-111.651302,Flagstaff,35.198284,56.50,55.69,58.84,...,62,43.65,0,3.44,200,NaN,NaN,NaN,NaN,NaN


We can drop longitude, latitude, and city_name because we are only doing one location, Flagstaff, Arizona. 

In [8]:
new_df = drop_nestedlist.drop(columns=["lat", "lon", "city_name"])
new_df.head(3) # shows us the first three rows of the dataset.

,dt,dt_iso,timezone,visibility,main.temp,main.temp_min,main.temp_max,main.feels_like,main.pressure,main.humidity,main.dew_point,clouds.all,wind.speed,wind.deg,wind.gust,rain.1h,rain.3h,snow.1h,snow.3h
0,1759280400,2025-10-01 01:00:00 +0000 UTC,-25200,10000.0,61.38,60.60,63.84,59.70,1016,53,44.11,0,9.22,200,NaN,NaN,NaN,NaN,NaN
1,1759284000,2025-10-01 02:00:00 +0000 UTC,-25200,10000.0,56.50,55.69,58.84,54.77,1017,62,43.65,0,3.44,200,NaN,NaN,NaN,NaN,NaN
2,1759287600,2025-10-01 03:00:00 +0000 UTC,-25200,10000.0,53.62,51.40,55.83,51.93,1017,69,43.72,0,0.00,0,NaN,NaN,NaN,NaN,NaN


Some things that we can clean up are:
- datetime_iso (dt_iso) because it's just a UTC conversion of dt (datetime). It will also be a bit challenging to work with models because of the numeric and categorical data mix for this one variable, so let's keep dt and drop dt_iso.
- timezone because they're all going to have the same timezone because the location is the same for all of the data (Flagstaff, Arizona).

That's all for now. 

In [9]:
new_df = new_df.drop(columns=["dt_iso", "timezone"])
new_df.head(3)

,dt,visibility,main.temp,main.temp_min,main.temp_max,main.feels_like,main.pressure,main.humidity,main.dew_point,clouds.all,wind.speed,wind.deg,wind.gust,rain.1h,rain.3h,snow.1h,snow.3h
0,1759280400,10000.0,61.38,60.60,63.84,59.70,1016,53,44.11,0,9.22,200,NaN,NaN,NaN,NaN,NaN
1,1759284000,10000.0,56.50,55.69,58.84,54.77,1017,62,43.65,0,3.44,200,NaN,NaN,NaN,NaN,NaN
2,1759287600,10000.0,53.62,51.40,55.83,51.93,1017,69,43.72,0,0.00,0,NaN,NaN,NaN,NaN,NaN


<h3> Exploratory Data Analysis </h3>

This step includes computing models such as XGBoost and Linear Regression. Later on, we are expecting to add in more models such as Random Forest Regressor. </h3>

XGBoost Model Training and Testing - 'Clouds' is the target feature (what we want to predict) and everything else as the features to train on (having the model study these features before testing it's knowledge.)

In [10]:
X = new_df.drop(columns="clouds.all") # getting rid of only the target column, which is Clouds
y = new_df["clouds.all"] # target column Clouds

In [11]:
dtrain = XGB.DMatrix(X, label=y)

In [12]:
params = {
    'objective': 'reg:squarederror',  # Use 'reg:squarederror' for regression
    'max_depth': 5,
    'learning_rate': 0.1,
    'eval_metric': 'logloss'
}

num_rounds = 100
bst = XGB.train(params, dtrain, num_boost_round=num_rounds)

In [13]:
model_file_name = 'Stargazers_XGBoost.json'
bst.save_model(model_file_name)

# Upload model to S3
s3.upload_file(model_file_name, BUCKET_NAME, f"models/{model_file_name}")


In [14]:
# Read training metrics or JSON results from S3
obj = s3.get_object(
    Bucket=BUCKET_NAME, Key=OBJECT_KEY
)
metrics_data = obj["Body"].read().decode("utf-8")
print(metrics_data)


[{"dt":1759276800,"dt_iso":"2025-10-01 00:00:00 +0000 UTC","timezone":-25200,"main":{"temp":64.74,"temp_min":63.59,"temp_max":65.84,"feels_like":63.12,"pressure":1016,"humidity":47,"dew_point":44.08},"clouds":{"all":20},"weather":[{"id":801,"main":"Clouds","description":"few clouds","icon":"02d"}],"visibility":10000,"wind":{"speed":14.97,"deg":210},"lon":-111.651302,"city_name":"Flagstaff","lat":35.198284},{"dt":1759280400,"dt_iso":"2025-10-01 01:00:00 +0000 UTC","timezone":-25200,"main":{"temp":61.38,"temp_min":60.6,"temp_max":63.84,"feels_like":59.7,"pressure":1016,"humidity":53,"dew_point":44.11},"clouds":{"all":0},"weather":[{"id":800,"main":"Clear","description":"sky is clear","icon":"01d"}],"visibility":10000,"wind":{"speed":9.22,"deg":200},"lon":-111.651302,"city_name":"Flagstaff","lat":35.198284},{"dt":1759284000,"dt_iso":"2025-10-01 02:00:00 +0000 UTC","timezone":-25200,"main":{"temp":56.5,"temp_min":55.69,"temp_max":58.84,"feels_like":54.77,"pressure":1017,"humidity":62,"dew_

In [15]:
new_df.isnull().sum()

dt                    0
visibility         5145
main.temp             0
main.temp_min         0
main.temp_max         0
main.feels_like       0
main.pressure         0
main.humidity         0
main.dew_point        0
clouds.all            0
wind.speed            0
wind.deg              0
wind.gust          5067
rain.1h            8428
rain.3h            9215
snow.1h            9233
snow.3h            9325
dtype: int64

From above we are able to see what columns contain null values and what columns don't. Wind_gust, rain.1h, rain.3h, snow.1h, snow.3h all have the most NaN values (null), meaning that it was possibly not calculated or not able to be calculated for that day. Since they have a high enough threshold of being majority (>50%) of the entire dataset, we might do some imputations to combat the nulls for further training. 

In [16]:
new_df = new_df.drop(columns=["wind.gust", "rain.1h", "rain.3h", "snow.1h", "snow.3h"])

Now let's see what our dataset is looking like now with most of the null values taken out.

In [17]:
new_df.isnull().sum()

dt                    0
visibility         5145
main.temp             0
main.temp_min         0
main.temp_max         0
main.feels_like       0
main.pressure         0
main.humidity         0
main.dew_point        0
clouds.all            0
wind.speed            0
wind.deg              0
dtype: int64

From above, you can see that we still have null values in visibility, so let's see if we can fill them in with the average of other days within the dataset using K-Nearest Neighbor (KNN) imputer later on. But first, let's start to prep our model by splitting up our dataset to make sure that we can train the model on unseen data.

In [19]:
X = new_df.drop(columns=["clouds.all"])
y = new_df["clouds.all"]

Now let's do Linear Regression with the same target and feature variables as before. (Clouds - clouds.all)

In [20]:
X_train, X_test, y_train, y_test = train_test_split(X, y, test_size=0.2, random_state=42)

In [21]:
X_train.shape, X_test.shape, y_train.shape, y_test.shape # showing row, columns counts of the X features and y target column Clouds

((7468, 11), (1867, 11), (7468,), (1867,))

In [ ]:
scaler = StandardScaler() # used to represent StandardScaler
X_train_scaled = scaler.fit_transform(X_train) # used to transform our X training features to better fit our model later on.
X_test_scaled = scaler.transform(X_test) # used to transform the data into usable data for our KNN imputations, these are scaled to make sure that the playing field is leveled for all features involved. 

<h3> K-Nearest Neighbors Imputations </h3>

In [23]:
from sklearn.impute import KNNImputer
imputer = KNNImputer(n_neighbors=5) # taking the 5 values closest to the data point based on feature similarity. 

In [24]:
X_train_imputed = imputer.fit_transform(X_train_scaled)
X_test_imputed = imputer.transform(X_test_scaled)

In [ ]:
X_train_clean = pd.DataFrame(X_train_imputed, columns=X.columns) # converts the data back into a dataframe for easy inspection in case we want to look at our dataset now vs before. 

Now that everything is more adjusted to our data, now we can move on to completing our linear regression. 

In [27]:
model = LinearRegression()
model.fit(X_train_imputed, y_train) # using the imputed data, the dataset that got filled with mean values of the closest neighbor value average

LinearRegression()

In [28]:
y_pred = model.predict(X_test_imputed) # testing to see what the model actually predicts for our dataset (clouds.all)

<h3> Model Metrics - R2 Score and MSE </h3>

In [30]:
score = r2_score(y_test, y_pred) # R2 score of the model on the test data
print("R2 Score:", score)

R2 Score: 0.2839969424069557


In [32]:
MSE = mean_squared_error(y_test, y_pred)
print(f"Mean Squared Error: {MSE}")

Mean_squared_error: 541.3367147295127
